Information Retrieval System 
- The system process text dataset about a NewsPaper using different methods and algorithms **without** using TF-IDF.    

In [1]:
#Importing all needed libraries 
import csv
import pickle
import re
import tkinter as tk
from collections import defaultdict
from sklearn.feature_extraction.text import CountVectorizer
from sklearn.model_selection import train_test_split
from sklearn.naive_bayes import MultinomialNB
from sklearn.metrics import accuracy_score
from sklearn.metrics import precision_score, recall_score, f1_score

#Processing data through numerous methodologies.
class InvertedIndex:
    def __init__(self, csv_file=None):
        self.csv_file = csv_file
        self.docs = []
        self.labels = []
        self.lines = 0
        self.inverted_index = defaultdict(set)
        self.indexer = {}
        self.vectorizer = None
        self.bow_matrix = None
        self.classifier = None

        if self.csv_file:
            self.add_csv_files(csv_files)

#Adding many documents to be processed for the same query
    def add_csv_files(self, csv_files):
        for csv_file in csv_files:
            self.add_csv(csv_file)

    def add_csv(self, csv_file):
        try:
            with open(csv_file, 'r') as file:
                reader = csv.reader(file)
                for row in reader:
                    if len(row) >= 2:
                        self.docs.append(row[0])
                        self.labels.append(row[1])
                        self.lines += 1
                    else:
                        print(f"Skipping row with insufficient columns: {row}")
        except Exception as e:
            print(f"Error reading CSV file: {e}")

# evaluating retrieval of certain queries by calculating precision, recall and F1 score.
    def evaluate_retrieval(self, queries, true_labels):
        all_precision = []
        all_recall = []
        all_f1 = []

        for query, true_set in zip(queries, true_labels):
            results = self.search(query)
            retrieved_docs = [doc for doc in results]

            # Generate predicted labels (binary: relevant or not)
            predicted_labels = [1 if doc in retrieved_docs else 0 for doc in range(len(self.docs))]

            # Generate true labels (binary: relevant or not)
            true_labels_binary = [1 if doc in true_set else 0 for doc in range(len(self.docs))]

            precision = precision_score(true_labels_binary, predicted_labels, zero_division=0)
            recall = recall_score(true_labels_binary, predicted_labels, zero_division=0)
            f1 = f1_score(true_labels_binary, predicted_labels, zero_division=0)

            all_precision.append(precision)
            all_recall.append(recall)
            all_f1.append(f1)

        avg_precision = sum(all_precision) / len(all_precision)
        avg_recall = sum(all_recall) / len(all_recall)
        avg_f1 = sum(all_f1) / len(all_f1)

        return avg_precision, avg_recall, avg_f1
           

# functions to return information about the documents. 
    def Display_docs(self):
        return self.docs

    def Number_of_docs(self):
        return self.lines
    
# Tokenizing the documents.
    def Tokenization(self):
        return [re.findall(r'\b\w+\b', doc.lower()) for doc in self.docs]

# Lemmatization of the documents.    
    def Lemmatization(self, tokens_list):
        return [[self.lemmatizer.lemmatize(token) for token in doc] for doc in tokens_list]

# removing all the stop words.
    def Stopping(self):
        with open('StopWords.txt', 'r') as file:
            stop_words = set(file.read().split())
        
        tokens_list = self.Tokenization()
        after_stopping = [[token for token in doc if token not in stop_words] for doc in tokens_list]
        return after_stopping

# function to process the data using inverted index method.   
    def build_inverted_index(self):
        after_stopping = self.Stopping()
        for i, doc in enumerate(after_stopping):
            for token in doc:
                self.inverted_index[token].add(i)

    def Inverted_Index(self):
        if not self.inverted_index:
            after_stopping = self.Stopping()
            for i, doc in enumerate(after_stopping):
                for token in doc:
                    self.inverted_index[token].add(i + 1)
        return dict(self.inverted_index)

    def Indexer(self):
        if not self.indexer:
            after_stopping = self.Stopping()
            for i, doc in enumerate(after_stopping):
                for token in doc:
                    self.indexer[token] = i + 1
        return self.indexer

# calculating frequency in each term.
    def Term_squences(self):
        indexer = self.Indexer()
        return sorted(indexer.items(), key=lambda x: x[1])

# sorting the terms.
    def Sorting_Alphabetically(self):
        indexer = self.Indexer()
        return sorted(indexer.items(), key=lambda x: x[0])

    def Term_Frequency(self):
        return {term: len(docs) for term, docs in self.Inverted_Index().items()}

# saving the file after it has been processed.
    def save_index(self, file_path):
        data = {
            'docs': self.docs,
            'labels': self.labels,
            'lines': self.lines,
            'inverted_index': dict(self.inverted_index),
            'indexer': self.indexer
        }
        with open(file_path, 'wb') as file:
            pickle.dump(data, file)
            
    def Split_docs(self):
        return self.docs

# Loading the file after it has been processed.   
    def load_index(self, file_path):
        with open(file_path, 'rb') as file:
            data = pickle.load(file)
            self.docs = data['docs']
            self.labels = data['labels']
            self.lines = data['lines']
            self.inverted_index = defaultdict(set, data['inverted_index'])
            self.indexer = data['indexer']

# Creates a Bag-of-Words matrix using CountVectorizer 
    def build_bow_matrix(self):
      if self.bow_matrix is None:
        self.vectorizer = CountVectorizer(stop_words='english')
        self.bow_matrix = self.vectorizer.fit_transform(self.docs)

    def train_classifier(self):
        """Train the Naive Bayes classifier on the document dataset."""
        self.build_bow_matrix()
        if not self.bow_matrix is None:
            self.build_bow_matrix()
        
        X_train, X_test, y_train, y_test = train_test_split(self.bow_matrix, self.labels, test_size=0.2, random_state=42)
        self.classifier = MultinomialNB()
        self.classifier.fit(X_train, y_train)
        y_pred = self.classifier.predict(X_test)
        accuracy = accuracy_score(y_test, y_pred)
        print(f'Classifier accuracy: {accuracy:.2f}')

    def classify_document(self, doc):
        """Classify a new document using the trained classifier."""
        if not self.classifier or not self.vectorizer:
            raise ValueError("Classifier or vectorizer not found. Train the classifier first.")
        
        doc_bow = self.vectorizer.transform([doc])
        return self.classifier.predict(doc_bow)[0]

# function to search the query in the processed document.
    def search(self, query):
        if not self.inverted_index:
            self.build_inverted_index()
        query_terms = re.findall(r'\b\w+\b', query.lower())
        result_docs = set()
        for term in query_terms:
            if term in self.inverted_index:
                result_docs.update(self.inverted_index[term])
        return sorted(result_docs)

class InvertedIndexGUI:
    def __init__(self, master, inverted_index):
        self.master = master
        self.inverted_index = inverted_index
        self.master.title("Inverted Index Search")
        
        self.label = tk.Label(master, text="Enter query:")
        self.label.pack()

        self.query_entry = tk.Entry(master, width=50)
        self.query_entry.pack()

        self.search_button = tk.Button(master, text="Search", command=self.search)
        self.search_button.pack()

        self.result_text = tk.Text(master, height=15, width=100)
        self.result_text.pack()

# GUI ask for the user input of the query and return back the documents where it was found.
    def search(self):
        query = self.query_entry.get()
        results = self.inverted_index.search(query)

        self.result_text.delete(1.0, tk.END)
        self.result_text.insert(tk.END, f"Found in {len(results)} documents:\n\n")
        for doc_index in results:
            self.result_text.insert(tk.END, f"Document {doc_index + 1}: {self.inverted_index.docs[doc_index]}\n")

if __name__ == "__main__":
    csv_files = [
        "C:/Users/Magic Systems/OneDrive/Desktop/NewspaperDataset/alt.atheism.csv",
        "C:/Users/Magic Systems/OneDrive/Desktop/NewspaperDataset/comp.graphics.csv"
        "C:/Users/Magic Systems/OneDrive/Desktop/NewspaperDataset/comp.sys.mac.hardware(zaid).csv",
        "C:/Users/Magic Systems/OneDrive/Desktop/NewspaperDataset/rec.motorcycles(zaid).csv"
        #  more CSV file paths can be added
    ]
    
    inverted_index = InvertedIndex(csv_files)
    inverted_index.build_bow_matrix()
    inverted_index.train_classifier()

    root = tk.Tk()
    app = InvertedIndexGUI(root, inverted_index)
    root.mainloop()



Skipping row with insufficient columns: ['From: mathew <mathew@mantis.co.uk>']
Skipping row with insufficient columns: ['Subject: Alt.Atheism FAQ: Atheist Resources']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['Archive-name: atheism/resources']
Skipping row with insufficient columns: ['Alt-atheism-archive-name: resources']
Skipping row with insufficient columns: ['Last-modified: 11 December 1992']
Skipping row with insufficient columns: ['Version: 1.0']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['                              Atheist Resources']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['                      Addresses of Atheist Organizations']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['                                     USA']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['FREEDOM F

In [2]:
# path to a document
csv_file = "C:/Users/Magic Systems/OneDrive/Desktop/NewspaperDataset/alt.atheism.csv"
InvIndex = InvertedIndex(csv_file)
InvIndex.Display_docs()

Skipping row with insufficient columns: ['From: mathew <mathew@mantis.co.uk>']
Skipping row with insufficient columns: ['Subject: Alt.Atheism FAQ: Atheist Resources']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['Archive-name: atheism/resources']
Skipping row with insufficient columns: ['Alt-atheism-archive-name: resources']
Skipping row with insufficient columns: ['Last-modified: 11 December 1992']
Skipping row with insufficient columns: ['Version: 1.0']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['                              Atheist Resources']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['                      Addresses of Atheist Organizations']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['                                     USA']
Skipping row with insufficient columns: []
Skipping row with insufficient columns: ['FREEDOM F

['Write to:  FFRF',
 'Evolution Designs sell the "Darwin fish".  It\'s a fish symbol',
 'Christians stick on their cars',
 'Write to:  Evolution Designs',
 'try mailing <figmo@netcom.com>.  For net people who go to Lynn directly',
 'AAP publish various atheist books -- critiques of the Bible',
 'Biblical contradictions',
 '372 pp.  ISBN 0-910309-26-4',
 'absurdities',
 'Contradicts Itself"',
 'Write to:  American Atheist Press',
 '      or:  7215 Cameron Road',
 'Write to:  700 East Amherst Street',
 'Prometheus Books',
 'black freethought.  They publish a quarterly newsletter',
 'Write to:  Norm R. Allen',
 '           Buffalo',
 'The National Secular Society publish "The Freethinker"',
 'Postfach 880',
 'MIZ-Vertrieb',
 'For atheist books',
 'IBDK',
 'Postfach 3005',
 'events are fictitious.  Any similarity to living or dead gods -- uh',
 'WALTER M. MILLER',
 'copying blueprints from "Saint Leibowitz"',
 'Post atomic doomsday novel set in clerical states.  The church',
 'forbids that

In [3]:
queries = ["atheism  ", "religion", "freedom speech"]
true_labels = [
    {1, 2, 3, 4},  # Relevant document indices for the first query
    {5, 6, 7},     # Relevant document indices for the second query
    {8, 9, 10}  ]

- Printing out the details of the document:

In [4]:
InvIndex.Number_of_docs()

42737

In [5]:
InvIndex.Split_docs()

['Write to:  FFRF',
 'Evolution Designs sell the "Darwin fish".  It\'s a fish symbol',
 'Christians stick on their cars',
 'Write to:  Evolution Designs',
 'try mailing <figmo@netcom.com>.  For net people who go to Lynn directly',
 'AAP publish various atheist books -- critiques of the Bible',
 'Biblical contradictions',
 '372 pp.  ISBN 0-910309-26-4',
 'absurdities',
 'Contradicts Itself"',
 'Write to:  American Atheist Press',
 '      or:  7215 Cameron Road',
 'Write to:  700 East Amherst Street',
 'Prometheus Books',
 'black freethought.  They publish a quarterly newsletter',
 'Write to:  Norm R. Allen',
 '           Buffalo',
 'The National Secular Society publish "The Freethinker"',
 'Postfach 880',
 'MIZ-Vertrieb',
 'For atheist books',
 'IBDK',
 'Postfach 3005',
 'events are fictitious.  Any similarity to living or dead gods -- uh',
 'WALTER M. MILLER',
 'copying blueprints from "Saint Leibowitz"',
 'Post atomic doomsday novel set in clerical states.  The church',
 'forbids that

In [6]:
InvIndex.Tokenization()

[['write', 'to', 'ffrf'],
 ['evolution',
  'designs',
  'sell',
  'the',
  'darwin',
  'fish',
  'it',
  's',
  'a',
  'fish',
  'symbol'],
 ['christians', 'stick', 'on', 'their', 'cars'],
 ['write', 'to', 'evolution', 'designs'],
 ['try',
  'mailing',
  'figmo',
  'netcom',
  'com',
  'for',
  'net',
  'people',
  'who',
  'go',
  'to',
  'lynn',
  'directly'],
 ['aap',
  'publish',
  'various',
  'atheist',
  'books',
  'critiques',
  'of',
  'the',
  'bible'],
 ['biblical', 'contradictions'],
 ['372', 'pp', 'isbn', '0', '910309', '26', '4'],
 ['absurdities'],
 ['contradicts', 'itself'],
 ['write', 'to', 'american', 'atheist', 'press'],
 ['or', '7215', 'cameron', 'road'],
 ['write', 'to', '700', 'east', 'amherst', 'street'],
 ['prometheus', 'books'],
 ['black', 'freethought', 'they', 'publish', 'a', 'quarterly', 'newsletter'],
 ['write', 'to', 'norm', 'r', 'allen'],
 ['buffalo'],
 ['the', 'national', 'secular', 'society', 'publish', 'the', 'freethinker'],
 ['postfach', '880'],
 ['miz

- Removing stopping words results:

In [7]:
InvIndex.Stopping()

[['write', 'ffrf'],
 ['evolution', 'designs', 'sell', 'darwin', 'fish', 's', 'fish', 'symbol'],
 ['christians', 'stick', 'cars'],
 ['write', 'evolution', 'designs'],
 ['try',
  'mailing',
  'figmo',
  'netcom',
  'com',
  'net',
  'people',
  'lynn',
  'directly'],
 ['aap', 'publish', 'various', 'atheist', 'books', 'critiques', 'bible'],
 ['biblical', 'contradictions'],
 ['372', 'pp', 'isbn', '0', '910309', '26', '4'],
 ['absurdities'],
 ['contradicts'],
 ['write', 'american', 'atheist', 'press'],
 ['7215', 'cameron', 'road'],
 ['write', '700', 'east', 'amherst', 'street'],
 ['prometheus', 'books'],
 ['black', 'freethought', 'publish', 'quarterly', 'newsletter'],
 ['write', 'norm', 'r', 'allen'],
 ['buffalo'],
 ['national', 'secular', 'society', 'publish', 'freethinker'],
 ['postfach', '880'],
 ['miz', 'vertrieb'],
 ['atheist', 'books'],
 ['ibdk'],
 ['postfach', '3005'],
 ['events', 'fictitious', 'similarity', 'living', 'dead', 'gods', 'uh'],
 ['walter', 'm', 'miller'],
 ['copying', 'b

- Inverted Index Results:

In [8]:
InvIndex.Indexer()

{'write': 28609,
 'ffrf': 28592,
 'evolution': 29009,
 'designs': 28595,
 'sell': 42586,
 'darwin': 28593,
 'fish': 29610,
 's': 42710,
 'symbol': 28593,
 'christians': 28594,
 'stick': 40549,
 'cars': 39666,
 'try': 42728,
 'mailing': 40847,
 'figmo': 28596,
 'netcom': 38735,
 'com': 42687,
 'net': 41178,
 'people': 42726,
 'lynn': 42091,
 'directly': 38854,
 'aap': 28599,
 'publish': 28611,
 'various': 37173,
 'atheist': 29298,
 'books': 42720,
 'critiques': 28599,
 'bible': 29603,
 'biblical': 28600,
 'contradictions': 28600,
 '372': 28601,
 'pp': 28601,
 'isbn': 28601,
 '0': 42624,
 '910309': 28601,
 '26': 37580,
 '4': 42689,
 'absurdities': 28602,
 'contradicts': 28603,
 'american': 37401,
 'press': 38575,
 '7215': 28605,
 'cameron': 28605,
 'road': 42714,
 '700': 28606,
 'east': 42645,
 'amherst': 37598,
 'street': 42594,
 'prometheus': 28607,
 'black': 42397,
 'freethought': 28608,
 'quarterly': 28608,
 'newsletter': 39848,
 'norm': 28667,
 'r': 42522,
 'allen': 28667,
 'buffalo

- Frequency of each term:

In [9]:
InvIndex.Term_squences()

[('neutral', 19854),
 ('cohesion', 19855),
 ('progression', 19855),
 ('agnosticism', 19865),
 ('scepticism', 19870),
 ('provably', 19877),
 ('primes', 19879),
 ('interacts', 19886),
 ('detectable', 19887),
 ('verifiable', 19890),
 ('presence', 19891),
 ('tendency', 19906),
 ('questioned', 19912),
 ('encroaching', 19919),
 ('legislate', 19920),
 ('encouraging', 19923),
 ('reforms', 19923),
 ('campaigns', 19924),
 ('discriminate', 19925),
 ('voters', 19926),
 ('lawmakers', 19926),
 ('intimidating', 19928),
 ('wasting', 19930),
 ('contribute', 19931),
 ('charities', 19931),
 ('upbringing', 19938),
 ('backlash', 19941),
 ('conformism', 19941),
 ('verdi', 19943),
 ('requiem', 19943),
 ('dress', 19944),
 ('dahmer', 19956),
 ('behave', 19963),
 ('watched', 19969),
 ('political', 19979),
 ('obtaining', 19983),
 ('vulnerable', 19985),
 ('comforting', 19986),
 ('searching', 19989),
 ('unhappy', 19989),
 ('immediate', 19992),
 ('doctors', 19997),
 ('competing', 19998),
 ('graphology', 20012),
 ('

In [10]:
InvIndex.Sorting_Alphabetically()

[('0', 42624),
 ('00', 39379),
 ('000', 37580),
 ('0000000004', 38408),
 ('0002', 36254),
 ('001326', 26895),
 ('001813', 38454),
 ('002631', 42523),
 ('0049', 36790),
 ('005131', 41405),
 ('0099', 36661),
 ('00pm', 41155),
 ('0111', 42646),
 ('0126', 38612),
 ('013423tan102', 24986),
 ('013657', 21565),
 ('013752', 41825),
 ('0180', 42243),
 ('02', 36617),
 ('023044', 20970),
 ('02451203', 36790),
 ('030334', 22953),
 ('030734', 20983),
 ('0317', 37377),
 ('033446', 20741),
 ('035125', 38600),
 ('035421edt', 24785),
 ('040606', 36696),
 ('041535', 25582),
 ('044405', 36665),
 ('044430', 25940),
 ('045032', 38534),
 ('05', 25493),
 ('050750', 23123),
 ('05apr93', 36790),
 ('06', 36817),
 ('062328', 27696),
 ('062438', 26880),
 ('07', 40368),
 ('0709', 38408),
 ('071823', 22299),
 ('08', 42409),
 ('080321', 25322),
 ('081052', 21881),
 ('081303', 23767),
 ('083340', 40747),
 ('084042', 20666),
 ('0901', 42630),
 ('0930', 25051),
 ('094', 41722),
 ('095220', 20891),
 ('095305', 42075),
 

In [11]:
InvIndex.Term_Frequency()

{'write': 42,
 'ffrf': 6,
 'evolution': 39,
 'designs': 12,
 'sell': 41,
 'darwin': 6,
 'fish': 12,
 's': 1399,
 'symbol': 9,
 'christians': 36,
 'stick': 21,
 'cars': 29,
 'try': 79,
 'mailing': 21,
 'figmo': 6,
 'netcom': 21,
 'com': 561,
 'net': 39,
 'people': 429,
 'lynn': 8,
 'directly': 44,
 'aap': 6,
 'publish': 21,
 'various': 48,
 'atheist': 177,
 'books': 77,
 'critiques': 6,
 'bible': 186,
 'biblical': 27,
 'contradictions': 9,
 '372': 6,
 'pp': 6,
 'isbn': 6,
 '0': 33,
 '910309': 6,
 '26': 22,
 '4': 132,
 'absurdities': 6,
 'contradicts': 6,
 'american': 34,
 'press': 11,
 '7215': 6,
 'cameron': 6,
 'road': 118,
 '700': 6,
 'east': 94,
 'amherst': 11,
 'street': 47,
 'prometheus': 9,
 'black': 40,
 'freethought': 6,
 'quarterly': 6,
 'newsletter': 8,
 'norm': 24,
 'r': 47,
 'allen': 12,
 'buffalo': 8,
 'national': 29,
 'secular': 30,
 'society': 100,
 'freethinker': 6,
 'postfach': 12,
 '880': 6,
 'miz': 6,
 'vertrieb': 6,
 'ibdk': 6,
 '3005': 6,
 'events': 51,
 'fictitious

In [12]:
InvIndex.save_index('indexed_data.pkl')


LoadedInvIndex = InvertedIndex()
LoadedInvIndex.load_index('indexed_data.pkl')

- Training Classifier

In [13]:
# Training the classifier
InvIndex.train_classifier()

Classifier accuracy: 0.17


- Testing the search for a query:

- Evaluation metrics calculated for a certain queries:

In [14]:
queries = ["humanism and uncovering", "Darwin fish bumper stickers"]
true_labels = [{17}, {2, 4}]  # Example true labels

# Evaluate the retrieval system
avg_precision, avg_recall, avg_f1 = InvIndex.evaluate_retrieval(queries, true_labels)
print(f"Retrieval System Metrics:")
print(f"Average Precision: {avg_precision:.2f}")
print(f"Average Recall: {avg_recall:.2f}")
print(f"Average F1 Score: {avg_f1:.2f}")


Retrieval System Metrics:
Average Precision: 0.02
Average Recall: 0.25
Average F1 Score: 0.04


In [15]:
def baseline_retrieval(query):
    # Implement a simple keyword-based retrieval system
    results = []
    for i, doc in enumerate(InvIndex.docs):
        if query.lower() in doc.lower():
            results.append(i)
    return results

# Evaluate the baseline retrieval system
baseline_avg_precision, baseline_avg_recall, baseline_avg_f1 = InvIndex.evaluate_retrieval(queries, true_labels)
print(f"Baseline Retrieval System Metrics:")
print(f"Average Precision: {baseline_avg_precision:.2f}")
print(f"Average Recall: {baseline_avg_recall:.2f}")
print(f"Average F1 Score: {baseline_avg_f1:.2f}")

Baseline Retrieval System Metrics:
Average Precision: 0.02
Average Recall: 0.25
Average F1 Score: 0.04


Made by:
- Ghazal Almidana
- Ayat Omar
- Zaid Eltabatebi